# Denoise benchmark v2: DeepFilterNet3 vs Sidon (русская речь)

Переработка ноутбука «Скачать MUSAN + Benchmark denoise». Структура и хорошие части оригинала сохранены: замороженный синтетический test-набор, SNR 0/5/10 дБ, фиксированный seed, общая нормировка пика, DeepFilterNet в отдельном окружении на Python 3.11, адаптер Sidon, пофайловые CSV.

**Что изменено и почему** (подробно в `CHANGES.md` рядом с ноутбуком):

| Было | Стало |
|---|---|
| Одна книга M-AILABS, одна дикторка | Common Voice 17 ru, test split: 160 дикторов, по одному клипу на каждого, каждый клип при всех трёх SNR (480 пар). CC0, нет в обучении Sidon (LibriTTS-R, FLEURS-R) и в clean-речи DNS Challenge, на которой учился DFN |
| MUSAN через `gdown` с чужого Drive, без проверки, `tarfile.extract` без фильтра | MUSAN noise с HF по закреплённой ревизии, sha256 каждого файла сверяется с LFS-метаданными этой ревизии. Архивов нет, распаковка zip с проверкой путей |
| `np.interp` для ресемплинга | soxr VHQ (с антиалиасингом) |
| SNR по RMS вместе с паузами | SNR по RMS активной речи (кадры в пределах 40 дБ от максимума), реальный SNR проверяется после записи |
| Набор перезаписывается при каждом запуске | Набор заморожен: `manifest.csv` с sha256 каждого файла и `testset.json` с хешем манифеста. Повторный запуск только сверяет хеши |
| Только ΔSI-SDR, без выравнивания | Решающие метрики, честные к генеративной модели: DNSMOS P.835, UTMOS22, CER (Whisper), ECAPA speaker similarity. SI-SDR/PESQ-WB/ESTOI после выравнивания кросс-корреляцией, как контроль для DFN |
| Sidon не подключён, RTF с загрузкой модели в каждом вызове | Sidon как в `tools/restore` harness. Обе модели на T4, модель грузится один раз, прогрев отдельно, RTF с `cuda.synchronize` |
| Средние без разброса | 95% bootstrap-CI и парная разница Sidon − DFN с CI |

**Запуск.** Colab, Runtime → T4 GPU, `RUN_MODE = 'full'`, Run all. Полный прогон занимает примерно 35–50 минут, большую часть съедают создание двух venv и Whisper. После обрыва сессии просто Run all снова: набор и готовые выходы на Drive не пересчитываются. `RUN_MODE = 'smoke'` (4 диктора, CPU) нужен только для проверки, что всё запускается.

**Ограничения, о которых надо помнить при чтении цифр.** Common Voice записан на бытовые микрофоны и хранится в MP3, поэтому «чистые» эталоны не студийные: проходят только клипы с DNSMOS OVRL ≥ 3.2 и BAK ≥ 3.9 (примерно верхние 25%). Сравнение идёт в полосе 16 кГц, так что выигрыш Sidon от расширения полосы до 48 кГц здесь не измеряется. UTMOS обучен на английском, для русского его абсолютные значения менее надёжны, чем разница между системами.

## 0. Настройки

In [1]:
RUN_MODE = 'full'          # 'full' на Colab T4; 'smoke' = 4 диктора, проверка на CPU
REBUILD_TESTSET = False    # True удалит замороженный набор И все выходы моделей и соберёт заново

import os, sys, json, shutil, subprocess, hashlib, time
from pathlib import Path

IN_COLAB = 'google.colab' in sys.modules
if IN_COLAB:
    from google.colab import drive
    drive.mount('/content/drive')
    # Токен HF из Colab Secrets (🔑 слева, имя HF_TOKEN, Notebook access включён). Без него HF быстро отвечает 429.
    try:
        from google.colab import userdata
        HF_TOKEN = "hf_REDACTED"
    except Exception as exc:
        print('HF_TOKEN не найден в Colab Secrets, качаю анонимно (возможен 429):', type(exc).__name__)
    DATA_ROOT = Path('/content/drive/MyDrive/audio-harness')  # долговременное: замороженный набор, выходы, результаты
    WORK = Path('/content/ah_bench')                           # локальный диск Colab: venv, кэши, сырые данные
else:
    DATA_ROOT = Path(os.environ.get('AH_BENCH_DATA', 'ah_bench_data')).resolve()
    WORK = Path(os.environ.get('AH_BENCH_WORK', 'ah_bench_work')).resolve()

HAS_GPU = shutil.which('nvidia-smi') is not None and subprocess.run(['nvidia-smi', '-L'], capture_output=True).returncode == 0
if RUN_MODE == 'full' and not HAS_GPU:
    raise RuntimeError('full-режим рассчитан на GPU (Runtime → Change runtime type → T4). Для проверки на CPU поставь RUN_MODE = "smoke".')

SEED = 42
SNRS_DB = [0, 5, 10]
N_SPEAKERS = 160 if RUN_MODE == 'full' else 4
CV_SHARDS = [f'ru/test-0000{i}-of-00008.parquet' for i in range(3)] if RUN_MODE == 'full' else ['ru/test-00000-of-00008.parquet']
CLIP_SECONDS = (3.0, 10.0)                   # длительность после обрезки тишины по краям
QUALITY = {'dnsmos_ovrl': 3.2, 'dnsmos_bak': 3.9, 'dnsmos_sig': 3.4}  # порог для «чистого» эталона
WHISPER = ('openai/whisper-large-v3-turbo', '41f01f3fe87f28c78e2fbf8b568835947dd65ed9') if RUN_MODE == 'full' \
    else ('openai/whisper-small', '973afd24965f72e36ca33b3055d56a652f456b4d')

# Всё, что скачивается, закреплено: ревизия (commit) для HF, sha256 для остального.
PINS = {
    'cv17': ('fixie-ai/common_voice_17_0', '34f78a43893414e7b6e271ba94c1d5e05f18b239'),
    'musan_noise': ('bilguun/musan-noise', 'd179de7b0c6adf58bf295495b481386b8fdb97c1'),
    'dfn3_zip': ('https://raw.githubusercontent.com/Rikorose/DeepFilterNet/main/models/DeepFilterNet3.zip',
                 '49c52edc8947ae1f9bf50d81530beaf3a2c3245aeaf34b6f31ff535cd22284d2'),
    'dnsmos_onnx': ('https://raw.githubusercontent.com/microsoft/DNS-Challenge/master/DNSMOS/DNSMOS/sig_bak_ovr.onnx',
                    '269fbebdb513aa23cddfbb593542ecc540284a91849ac50516870e1ac78f6edd'),
    'sidon': ('sarulab-speech/sidon-v0.1', 'b3b02d8bbd55fdbc410e6e46e76ef95ace4fbf52'),
    'w2v_bert': ('facebook/w2v-bert-2.0', 'da985ba0987f70aaeb84a80f2851cfac8c697a7b'),
    'utmos': ('prj-beatrice/utmos22-torch-native', 'eecd3e6e7ad9dd794308a4338c3ac7cb34691af9'),
    'ecapa': ('speechbrain/spkrec-ecapa-voxceleb', '0f99f2d0ebe89ac095bcc5903c4dd8f72b367286'),
    'whisper': WHISPER,
}

EVAL_ROOT = DATA_ROOT / 'derived' / f'denoise_eval_v2_{RUN_MODE}'
BENCH = WORK / 'bench'
for path in (DATA_ROOT, WORK, BENCH, WORK / 'raw', WORK / 'models'):
    path.mkdir(parents=True, exist_ok=True)
print('GPU:', HAS_GPU, '| набор и результаты:', EVAL_ROOT, '| рабочая папка:', WORK)

Mounted at /content/drive
GPU: True | набор и результаты: /content/drive/MyDrive/audio-harness/derived/denoise_eval_v2_full | рабочая папка: /content/ah_bench


## 1. Окружения

Ядро Colab только оркестрирует и собирает набор (numpy, soundfile, soxr, pyarrow). Модели и метрики работают в двух закреплённых venv:

* `df311`: Python 3.11, torch 2.3.1, DeepFilterNet 0.5.6. У `DeepFilterLib==0.5.6` нет колёс под cp312, поэтому отдельный интерпретатор, как у тебя.
* `ev312`: Python 3.12, torch 2.8.0, Sidon и все метрики. Версия torch закреплена, потому что предустановленный в Colab torch меняется, а speechbrain 1.0.3 ломается на torchaudio ≥ 2.9.

venv лежат на локальном диске Colab и создаются заново в каждой сессии (около 3–5 минут, uv кэширует колёса).

In [2]:
%pip -q install soxr pyarrow "huggingface_hub>=0.34,<1.0" uv

def sh(cmd, **kwargs):
    """Run a command and stream its output into the notebook; fail loudly on a non-zero exit."""
    print('$', ' '.join(map(str, cmd)), flush=True)
    proc = subprocess.Popen([str(c) for c in cmd], stdout=subprocess.PIPE, stderr=subprocess.STDOUT, text=True, **kwargs)
    for line in proc.stdout:
        print(line, end='', flush=True)
    if proc.wait() != 0:
        raise subprocess.CalledProcessError(proc.returncode, cmd)

UV = shutil.which('uv') or str(Path(sys.executable).parent / 'uv')
TORCH_INDEX = {
    'df311': 'https://download.pytorch.org/whl/cu121' if HAS_GPU else 'https://download.pytorch.org/whl/cpu',
    'ev312': 'https://download.pytorch.org/whl/cu126' if HAS_GPU else 'https://download.pytorch.org/whl/cpu',
}
VENV_SPECS = {
    'df311': ('3.11', ['torch==2.3.1', 'torchaudio==2.3.1'],
              ['DeepFilterNet==0.5.6', 'soundfile==0.13.1', 'numpy<2']),
    'ev312': ('3.12', ['torch==2.8.0', 'torchaudio==2.8.0'],
              ['transformers==4.56.2', 'huggingface_hub>=0.34,<1.0', 'speechbrain==1.0.3', 'onnxruntime==1.23.2',
               'pesq==0.0.4', 'pystoi==0.4.1', 'jiwer==4.0.0', 'soundfile==0.13.1', 'soxr==1.0.0', 'scipy', 'numpy<2.3']),
}

def make_venv(name):
    python, torch_pkgs, extra = VENV_SPECS[name]
    root = WORK / 'venvs' / name
    py = root / 'bin' / 'python'
    marker = root / 'spec.json'
    spec = json.dumps([python, torch_pkgs, extra, TORCH_INDEX[name]])
    if py.exists() and marker.exists() and marker.read_text() == spec:
        return py
    shutil.rmtree(root, ignore_errors=True)
    sh([UV, 'venv', '-q', '--python', python, root])
    sh([UV, 'pip', 'install', '-q', '--python', py, *torch_pkgs, '--index-url', TORCH_INDEX[name]])
    sh([UV, 'pip', 'install', '-q', '--python', py, *extra])
    marker.write_text(spec)
    return py

PY_DF = make_venv('df311')
PY_EV = make_venv('ev312')
sh([PY_DF, '-c', 'import torch, df; print("df311 ok, torch", torch.__version__, "cuda", torch.cuda.is_available())'])
sh([PY_EV, '-c', 'import torch, transformers; print("ev312 ok, torch", torch.__version__, "cuda", torch.cuda.is_available())'])

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 566.4/566.4 kB 13.5 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 17.2/17.2 MB 54.5 MB/s eta 0:00:00
ERROR: pip's dependency resolver does not currently take into account all the packages that are installed. This behaviour is the source of the following dependency conflicts.
diffusers 0.41.0 requires huggingface-hub<2.0,>=1.32.0, but you have huggingface-hub 0.36.2 which is incompatible.
gradio 6.30.0 requires huggingface-hub<3.0,>=1.16.0, but you have huggingface-hub 0.36.2 which is incompatible.
transformers 5.20.1 requires huggingface-hub<3.0,>=1.31.0, but you have huggingface-hub 0.36.2 which is incompatible.
gradio-client 2.7.2 requires huggingface-hub<3.0,>=1.16.0, but you have huggingface-hub 0.36.2 which is incompatible.
$ /usr/local/bin/uv venv -q --python 3.11 /content/ah_bench/venvs/df311
$ /usr/local/bin/uv pip install -q --python /content/ah_bench/venvs/df311/bin/python torch==2.3.1 torchaudio==2.3.1 --index-url ht

## 2. Загрузка с проверкой целостности

`gdown` с чужого Google Drive заменён. Для HF скачивается конкретный commit, и sha256 каждого LFS-файла сверяется с метаданными этого commit. Для файлов не с HF задан sha256: при несовпадении файл удаляется, и ячейка падает. Zip распаковывается с проверкой, что ни один путь не выходит за целевую папку. Если когда-нибудь будешь брать MUSAN с openslr одним `tar.gz`, распаковывай его только через `tarfile.extractall(dest, filter='data')`.

In [3]:
import urllib.request, zipfile
from huggingface_hub import HfApi, snapshot_download

def sha256_file(path, chunk=1 << 20):
    digest = hashlib.sha256()
    with open(path, 'rb') as handle:
        for block in iter(lambda: handle.read(chunk), b''):
            digest.update(block)
    return digest.hexdigest()

def fetch_url(url, sha256, dest):
    dest = Path(dest)
    if dest.exists() and sha256_file(dest) == sha256:
        return dest
    tmp = dest.with_suffix(dest.suffix + '.part')
    with urllib.request.urlopen(url) as response, open(tmp, 'wb') as handle:
        shutil.copyfileobj(response, handle)
    actual = sha256_file(tmp)
    if actual != sha256:
        tmp.unlink()
        raise RuntimeError(f'sha256 mismatch for {url}: {actual} != {sha256}')
    tmp.replace(dest)
    return dest

def hf_verified(repo_id, revision, local_dir, allow_patterns, repo_type='dataset'):
    """snapshot_download of one commit + sha256 check of every LFS file against that commit's metadata."""
    local_dir = Path(local_dir)
    from huggingface_hub.utils import HfHubHTTPError
    for attempt in range(6):   # 429 от HF: ждём и докачиваем, уже скачанные файлы не повторяются
        try:
            snapshot_download(repo_id, revision=revision, repo_type=repo_type, local_dir=local_dir,
                              allow_patterns=allow_patterns, max_workers=4)
            break
        except HfHubHTTPError as exc:
            if getattr(exc.response, 'status_code', None) != 429 or attempt == 5:
                raise
            wait = 30 * 2 ** attempt
            print(f'HF 429 (rate limit), повтор через {wait} с. Лучше добавить HF_TOKEN в Colab Secrets.')
            time.sleep(wait)
    marker = local_dir / f'.verified-{revision}'
    if marker.exists():
        return local_dir
    import fnmatch
    tree = HfApi().list_repo_tree(repo_id, revision=revision, repo_type=repo_type, recursive=True)
    checked = 0
    for item in tree:
        lfs = getattr(item, 'lfs', None)
        if lfs is None or not any(fnmatch.fnmatch(item.path, pat) for pat in allow_patterns):
            continue
        actual = sha256_file(local_dir / item.path)
        if actual != lfs.sha256:
            raise RuntimeError(f'{repo_id}@{revision}: sha256 mismatch for {item.path}')
        checked += 1
    assert checked, f'{repo_id}: no LFS files matched {allow_patterns}'
    marker.write_text(str(checked))
    print(f'{repo_id}@{revision[:8]}: sha256 ok for {checked} files')
    return local_dir

def safe_unzip(archive, dest):
    dest = Path(dest).resolve()
    with zipfile.ZipFile(archive) as zf:
        for name in zf.namelist():
            if not (dest / name).resolve().is_relative_to(dest):
                raise RuntimeError(f'unsafe path in {archive}: {name}')
        zf.extractall(dest)

## 3. Код инструментов

Три скрипта пишутся в `WORK/bench` и запускаются в своих venv. Их полезно прочитать: в комментариях объяснено, что и почему измеряется.

In [4]:
%%writefile {BENCH}/metrics.py
"""Metrics for the denoise benchmark (Python 3.12 eval venv).

  screen    DNSMOS P.835 + duration for candidate clean clips (quality gate for the test set)
  evaluate  all metrics for the systems clean / noisy / deepfilter / sidon -> metrics/<system>.csv

Everything is compared at 16 kHz: the clean references are 16 kHz, and DNSMOS, Whisper, ECAPA
and PESQ-WB all work at 16 kHz. Resampling is soxr VHQ (band-limited), not linear interpolation.

Two groups of metrics:
  * fair to a generative model (the decision metrics): DNSMOS SIG/BAK/OVRL, UTMOS22, Whisper CER,
    ECAPA speaker similarity to the clean reference;
  * sample-level (intrusive): SI-SDR, PESQ-WB, ESTOI. Computed after cross-correlation alignment,
    with the found lag reported. Sidon resynthesises the waveform (phase is not preserved), so
    these numbers are a sanity check for DeepFilterNet only, not a basis for comparing the two.
"""
import argparse
import csv
import json
import re
from pathlib import Path

import numpy as np
import soundfile as sf
import soxr

SR = 16_000
TARGET_DBFS = -26.0
MAX_LAG_MS = 40


def load16(path):
    audio, sr = sf.read(path, dtype='float32', always_2d=False)
    if audio.ndim == 2:
        audio = audio.mean(axis=1)
    if sr != SR:
        audio = soxr.resample(audio, sr, SR, quality='VHQ').astype(np.float32)
    return audio


def active_rms(audio, frame=320, floor_db=40.0):
    """RMS over frames within floor_db of the loudest frame: pauses do not dilute the level."""
    n = len(audio) // frame
    if n == 0:
        return float(np.sqrt(np.mean(audio.astype(np.float64) ** 2)) + 1e-12)
    energy = np.mean(audio[:n * frame].astype(np.float64).reshape(n, frame) ** 2, axis=1) + 1e-20
    db = 10 * np.log10(energy)
    return float(np.sqrt(np.mean(energy[db > db.max() - floor_db])))


def normalize_level(audio):
    return (audio * (10 ** (TARGET_DBFS / 20) / active_rms(audio))).astype(np.float32)


def align(estimate, reference, max_lag=int(SR * MAX_LAG_MS / 1000)):
    """Shift estimate by the lag that maximises cross-correlation within +-max_lag samples."""
    from scipy.signal import correlate
    n = min(len(estimate), len(reference))
    corr = correlate(estimate[:n], reference[:n], mode='full', method='fft')
    mid = n - 1
    window = corr[mid - max_lag: mid + max_lag + 1]
    lag = int(np.argmax(window)) - max_lag  # > 0: estimate lags behind the reference
    if lag > 0:
        shifted = np.concatenate([estimate[lag:], np.zeros(lag, np.float32)])
    elif lag < 0:
        shifted = np.concatenate([np.zeros(-lag, np.float32), estimate[:lag]])
    else:
        shifted = estimate
    shifted = shifted[:len(reference)]
    if len(shifted) < len(reference):
        shifted = np.pad(shifted, (0, len(reference) - len(shifted)))
    return shifted, lag


def si_sdr(estimate, reference):
    estimate = estimate.astype(np.float64) - estimate.mean()
    reference = reference.astype(np.float64) - reference.mean()
    scale = np.dot(estimate, reference) / max(np.dot(reference, reference), 1e-12)
    target = scale * reference
    residual = estimate - target
    return float(10 * np.log10(max(np.dot(target, target), 1e-12) / max(np.dot(residual, residual), 1e-12)))


class DNSMOS:
    """Official DNSMOS P.835 (sig_bak_ovr.onnx), same windowing and polynomial mapping as dnsmos_local.py."""
    INPUT_LENGTH = 9.01

    def __init__(self, model_path):
        import onnxruntime as ort
        self.session = ort.InferenceSession(str(model_path), providers=['CPUExecutionProvider'])
        self.p_ovr = np.poly1d([-0.06766283, 1.11546468, 0.04602535])
        self.p_sig = np.poly1d([-0.08397278, 1.22083953, 0.0052439])
        self.p_bak = np.poly1d([-0.13166888, 1.60915514, -0.39604546])

    def __call__(self, audio):
        audio = audio.astype(np.float32)
        length = int(self.INPUT_LENGTH * SR)
        while len(audio) < length:
            audio = np.append(audio, audio)
        hops = int(np.floor(len(audio) / SR) - self.INPUT_LENGTH) + 1
        scores = []
        for idx in range(hops):
            seg = audio[idx * SR: idx * SR + length]
            if len(seg) < length:
                continue
            sig, bak, ovr = self.session.run(None, {'input_1': seg[np.newaxis, :]})[0][0]
            scores.append((self.p_sig(sig), self.p_bak(bak), self.p_ovr(ovr)))
        sig, bak, ovr = np.mean(scores, axis=0)
        return {'dnsmos_sig': float(sig), 'dnsmos_bak': float(bak), 'dnsmos_ovrl': float(ovr)}


def normalize_text(text):
    text = text.lower().replace('ё', 'е')
    text = re.sub(r'[^\w\s]', ' ', text)
    return re.sub(r'\s+', ' ', text).strip()


def cmd_screen(args):
    dnsmos = DNSMOS(args.dnsmos_model)
    files = sorted(Path(args.input_dir).glob('*.wav'))
    with open(args.output, 'w', newline='', encoding='utf-8') as handle:
        writer = csv.DictWriter(handle, fieldnames=['file', 'seconds', 'dnsmos_sig', 'dnsmos_bak', 'dnsmos_ovrl'])
        writer.writeheader()
        for path in files:
            audio = load16(path)
            writer.writerow({'file': path.name, 'seconds': len(audio) / SR, **dnsmos(normalize_level(audio))})
    print('screened', len(files), '->', args.output)


def cmd_evaluate(args):
    import torch
    root = Path(args.root)
    device = 'cuda' if torch.cuda.is_available() else 'cpu'
    rows = list(csv.DictReader((root / 'manifest.csv').open(encoding='utf-8')))
    out_dir = root / 'metrics'
    out_dir.mkdir(exist_ok=True)

    dnsmos = DNSMOS(args.dnsmos_model)
    from transformers import AutoModel, pipeline
    utmos = AutoModel.from_pretrained('prj-beatrice/utmos22-torch-native', revision=args.utmos_revision,
                                      trust_remote_code=True).eval().to(device)
    asr = pipeline('automatic-speech-recognition', model=args.whisper, revision=args.whisper_revision,
                   dtype=torch.float16 if device == 'cuda' else torch.float32, device=device)
    from speechbrain.inference.speaker import EncoderClassifier
    ecapa = EncoderClassifier.from_hparams(source='speechbrain/spkrec-ecapa-voxceleb', revision=args.ecapa_revision,
                                           savedir=str(Path(args.cache) / 'ecapa'), run_opts={'device': device})
    from pesq import pesq, PesqError
    from pystoi import stoi
    import jiwer

    def embed(audio):
        with torch.inference_mode():
            emb = ecapa.encode_batch(torch.from_numpy(audio).unsqueeze(0).to(device)).squeeze()
        return torch.nn.functional.normalize(emb, dim=0).cpu()

    clean_cache = {}

    def clean_ref(rel):
        if rel not in clean_cache:
            audio = load16(root / rel)
            clean_cache[rel] = (audio, embed(normalize_level(audio)))
        return clean_cache[rel]

    for system in args.systems:
        target = out_dir / f'{system}.csv'
        if system == 'clean':
            # one row per clean clip; this is the ceiling for the non-intrusive metrics and the CER floor
            items, seen = [], set()
            for row in rows:
                if row['clean'] not in seen:
                    seen.add(row['clean'])
                    items.append((row['clean_id'], row['clean'], row))
        else:
            items = [(row['id'], row['noisy'] if system == 'noisy' else f"{system}/{row['id']}.wav", row) for row in rows]
        missing = [i for i, rel, _ in items if not (root / rel).exists()]
        if missing:
            print(f'{system}: missing {len(missing)} outputs (e.g. {missing[:3]}), skipping system')
            continue
        if target.exists() and len(list(csv.DictReader(target.open(encoding='utf-8')))) == len(items):
            print(f'{system}: already evaluated')
            continue
        audios = [load16(root / rel) for _, rel, _ in items]
        texts = asr([a for a in audios], batch_size=args.batch_size,
                    generate_kwargs={'language': 'russian', 'task': 'transcribe'})
        records = []
        for (item_id, rel, row), audio, hyp in zip(items, audios, texts):
            ref_audio, ref_emb = clean_ref(row['clean'])
            level = normalize_level(audio)
            rec = {'id': item_id, 'system': system, **dnsmos(level)}
            with torch.inference_mode():
                rec['utmos'] = float(utmos(torch.from_numpy(level).to(device), sampling_rate=SR).scores[0])
            reference_text = normalize_text(row['sentence'])
            rec['hyp'] = normalize_text(hyp['text'])
            rec['cer'] = float(jiwer.cer(reference_text, rec['hyp'])) if rec['hyp'] else 1.0
            rec['spk_sim'] = float(torch.dot(embed(level), ref_emb))
            if system != 'clean':
                aligned, lag = align(audio, ref_audio)
                rec['lag_ms'] = 1000 * lag / SR
                rec['si_sdr'] = si_sdr(aligned, ref_audio)
                rec['si_sdr_unaligned'] = si_sdr(np.pad(audio, (0, max(0, len(ref_audio) - len(audio))))[:len(ref_audio)], ref_audio)
                try:
                    rec['pesq_wb'] = float(pesq(SR, ref_audio, aligned, 'wb'))
                except PesqError:
                    rec['pesq_wb'] = float('nan')
                rec['estoi'] = float(stoi(ref_audio, aligned, SR, extended=True))
            records.append(rec)
        fields = list(dict.fromkeys(k for r in records for k in r))
        with target.open('w', newline='', encoding='utf-8') as handle:
            writer = csv.DictWriter(handle, fieldnames=fields)
            writer.writeheader()
            writer.writerows(records)
        print(f'{system}: {len(records)} rows -> {target}', flush=True)

    (out_dir / 'eval_info.json').write_text(json.dumps({
        'device': device, 'whisper': f'{args.whisper}@{args.whisper_revision}',
        'utmos': f'prj-beatrice/utmos22-torch-native@{args.utmos_revision}',
        'ecapa': f'speechbrain/spkrec-ecapa-voxceleb@{args.ecapa_revision}', 'dnsmos': 'P.835 sig_bak_ovr.onnx',
        'level_dbfs': TARGET_DBFS, 'max_lag_ms': MAX_LAG_MS,
    }, indent=2))


p = argparse.ArgumentParser()
sub = p.add_subparsers(dest='cmd', required=True)
s = sub.add_parser('screen')
s.add_argument('--input-dir', required=True)
s.add_argument('--output', required=True)
s.add_argument('--dnsmos-model', required=True)
e = sub.add_parser('evaluate')
e.add_argument('--root', required=True)
e.add_argument('--systems', nargs='+', default=['clean', 'noisy', 'deepfilter', 'sidon'])
e.add_argument('--dnsmos-model', required=True)
e.add_argument('--whisper', required=True)
e.add_argument('--whisper-revision', required=True)
e.add_argument('--utmos-revision', required=True)
e.add_argument('--ecapa-revision', required=True)
e.add_argument('--cache', required=True)
e.add_argument('--batch-size', type=int, default=8)
args = p.parse_args()
{'screen': cmd_screen, 'evaluate': cmd_evaluate}[args.cmd](args)

Writing /content/ah_bench/bench/metrics.py


In [5]:
%%writefile {BENCH}/run_deepfilter.py
"""DeepFilterNet3 runner (Python 3.11 venv). Loads the model once, warms up, times each file.

Output: <out>/<id>.wav as float32 at the model rate (48 kHz) plus timings.csv and run_info.json.
Files that already exist are skipped, so a Colab disconnect only costs the unfinished part.
"""
import argparse
import csv
import json
import time
from pathlib import Path

import soundfile as sf
import torch
from df.enhance import enhance, init_df
from df.io import load_audio

p = argparse.ArgumentParser()
p.add_argument('--root', type=Path, required=True)
p.add_argument('--model-dir', type=Path, required=True)
p.add_argument('--output-dir', type=Path, required=True)
args = p.parse_args()
args.output_dir.mkdir(parents=True, exist_ok=True)


def sync():
    if torch.cuda.is_available():
        torch.cuda.synchronize()


started = time.perf_counter()
model, state, _ = init_df(model_base_dir=str(args.model_dir), log_file=None, log_level='WARNING')
sync()
load_seconds = time.perf_counter() - started
device = str(next(model.parameters()).device)
rows = list(csv.DictReader((args.root / 'manifest.csv').open(encoding='utf-8')))

# Warm-up on the first file: CUDA kernels, cuDNN autotune and allocator are not part of RTF.
warm, _ = load_audio(str(args.root / rows[0]['noisy']), sr=state.sr(), verbose=False)
started = time.perf_counter()
enhance(model, state, warm)
sync()
warmup_seconds = time.perf_counter() - started

timings_path = args.output_dir / 'timings.csv'
done = set()
if timings_path.exists():
    done = {r['id'] for r in csv.DictReader(timings_path.open(encoding='utf-8'))}
new_file = not timings_path.exists()
with timings_path.open('a', newline='', encoding='utf-8') as handle:
    writer = csv.DictWriter(handle, fieldnames=['id', 'seconds', 'audio_seconds'])
    if new_file:
        writer.writeheader()
    for index, row in enumerate(rows, 1):
        target = args.output_dir / f"{row['id']}.wav"
        if row['id'] in done and target.exists():
            continue
        # load_audio resamples 16 kHz -> 48 kHz with torchaudio's sinc resampler (band-limited, not np.interp).
        audio, _ = load_audio(str(args.root / row['noisy']), sr=state.sr(), verbose=False)
        sync()
        t0 = time.perf_counter()
        enhanced = enhance(model, state, audio)  # pad=True: output is delay-compensated and has the input length
        sync()
        elapsed = time.perf_counter() - t0
        # float32 on disk: DFN's own save_audio casts to int16 without clamping and wraps around on overs.
        sf.write(target, enhanced.squeeze(0).cpu().numpy(), state.sr(), subtype='FLOAT')
        writer.writerow({'id': row['id'], 'seconds': f'{elapsed:.6f}', 'audio_seconds': f"{audio.shape[-1] / state.sr():.6f}"})
        handle.flush()
        print(f"{index}/{len(rows)} {row['id']}: {elapsed:.3f}s", flush=True)

(args.output_dir / 'run_info.json').write_text(json.dumps({
    'model': 'DeepFilterNet3 (DeepFilterNet==0.5.6)', 'device': device, 'torch': torch.__version__,
    'load_seconds': load_seconds, 'warmup_seconds': warmup_seconds, 'output_sample_rate': state.sr(),
}, indent=2))
print('device', device, '| load', round(load_seconds, 2), 's | warm-up', round(warmup_seconds, 2), 's')

Writing /content/ah_bench/bench/run_deepfilter.py


In [6]:
%%writefile {BENCH}/run_sidon.py
"""Sidon v0.1 runner (Python 3.12 eval venv). Same inference path as tools/restore in the harness.

Follows the official demo (huggingface.co/spaces/sarulab-speech/sidon_demo_beta): TorchScript
w2v-BERT 2.0 feature predictor + TorchScript vocoder, 16 kHz in, 48 kHz out. The model is loaded
once; load time and warm-up are reported separately and are not part of RTF.
"""
import argparse
import csv
import json
import time
from pathlib import Path

import numpy as np
import soundfile as sf
import soxr
import torch
import torchaudio
from huggingface_hub import hf_hub_download
from transformers import SeamlessM4TFeatureExtractor

IN_SR, OUT_SR = 16_000, 48_000
TAIL_PAD, FRAME_PAD, TRIM = 24_000, 160, 960  # from the official demo
CHUNK_SECONDS = 96.0

p = argparse.ArgumentParser()
p.add_argument('--root', type=Path, required=True)
p.add_argument('--output-dir', type=Path, required=True)
p.add_argument('--revision', required=True)
p.add_argument('--preprocessor-revision', required=True)
p.add_argument('--device', default='cuda' if torch.cuda.is_available() else 'cpu')
args = p.parse_args()
args.output_dir.mkdir(parents=True, exist_ok=True)
device = args.device


def sync():
    if device.startswith('cuda'):
        torch.cuda.synchronize()


started = time.perf_counter()
suffix = 'cuda' if device.startswith('cuda') else 'cpu'
fe_path = hf_hub_download('sarulab-speech/sidon-v0.1', f'feature_extractor_{suffix}.pt', revision=args.revision)
decoder_path = hf_hub_download('sarulab-speech/sidon-v0.1', f'decoder_{suffix}.pt', revision=args.revision)
preprocessor = SeamlessM4TFeatureExtractor.from_pretrained('facebook/w2v-bert-2.0', revision=args.preprocessor_revision)
fe = torch.jit.load(fe_path, map_location=device).to(device).eval()
decoder = torch.jit.load(decoder_path, map_location=device).to(device).eval()
sync()
load_seconds = time.perf_counter() - started


def restore(mono: np.ndarray, sr: int) -> np.ndarray:
    peak = float(np.max(np.abs(mono)))
    if peak == 0:
        raise ValueError('input is digital silence')
    wave = torch.from_numpy(0.9 * mono / peak).float().view(1, -1)
    wave = torchaudio.functional.highpass_biquad(wave, sr, 50)
    wave16 = wave.view(-1).numpy()
    if sr != IN_SR:
        wave16 = soxr.resample(wave16, sr, IN_SR, quality='VHQ')
    wave16 = np.pad(wave16, (0, TAIL_PAD))
    restored, cache = [], None
    with torch.inference_mode():
        for chunk in torch.from_numpy(wave16).split(int(IN_SR * CHUNK_SECONDS)):
            inputs = preprocessor(torch.nn.functional.pad(chunk, (FRAME_PAD, FRAME_PAD)).numpy(),
                                  sampling_rate=IN_SR, return_tensors='pt')
            feature = fe(inputs['input_features'].to(device))['last_hidden_state']
            if cache is not None:
                feature = torch.cat([cache, feature], dim=1)
            restored.append(decoder(feature.transpose(1, 2)).view(-1)[:-TRIM].cpu())
            cache = feature[:, -1:]
    return torch.cat(restored).numpy()[:int(OUT_SR / sr * mono.shape[0])]


rows = list(csv.DictReader((args.root / 'manifest.csv').open(encoding='utf-8')))
warm, warm_sr = sf.read(args.root / rows[0]['noisy'], dtype='float32')
sync()
t0 = time.perf_counter()
restore(warm, warm_sr)
sync()
warmup_seconds = time.perf_counter() - t0

timings_path = args.output_dir / 'timings.csv'
done = set()
if timings_path.exists():
    done = {r['id'] for r in csv.DictReader(timings_path.open(encoding='utf-8'))}
new_file = not timings_path.exists()
with timings_path.open('a', newline='', encoding='utf-8') as handle:
    writer = csv.DictWriter(handle, fieldnames=['id', 'seconds', 'audio_seconds'])
    if new_file:
        writer.writeheader()
    for index, row in enumerate(rows, 1):
        target = args.output_dir / f"{row['id']}.wav"
        if row['id'] in done and target.exists():
            continue
        noisy, sr = sf.read(args.root / row['noisy'], dtype='float32')
        sync()
        t0 = time.perf_counter()
        out = restore(noisy, sr)
        sync()
        elapsed = time.perf_counter() - t0
        sf.write(target, out.astype(np.float32), OUT_SR, subtype='FLOAT')
        writer.writerow({'id': row['id'], 'seconds': f'{elapsed:.6f}', 'audio_seconds': f'{len(noisy) / sr:.6f}'})
        handle.flush()
        print(f"{index}/{len(rows)} {row['id']}: {elapsed:.3f}s", flush=True)

(args.output_dir / 'run_info.json').write_text(json.dumps({
    'model': f'sarulab-speech/sidon-v0.1@{args.revision}', 'device': device, 'torch': torch.__version__,
    'load_seconds': load_seconds, 'warmup_seconds': warmup_seconds, 'output_sample_rate': OUT_SR,
}, indent=2))
print('device', device, '| load', round(load_seconds, 2), 's | warm-up', round(warmup_seconds, 2), 's')

Writing /content/ah_bench/bench/run_sidon.py


## 4. Шумы MUSAN и чистая речь Common Voice ru

**Шумы.** MUSAN `noise` (CC BY 4.0, 930 файлов, около 0.7 ГБ) с зеркала на HF по закреплённому commit. Зеркало стороннее, поэтому ревизия закреплена: тихо подменить файлы оно не сможет. Подкаталог (`free-sound` или `sound-bible`) пишется в манифест. Freesound есть и в шумах DNS Challenge, на которых учился DFN, так что по `noise_subset` можно проверить, нет ли у DFN преимущества на знакомых шумах.

**Речь.** Почему Common Voice 17 ru (test split), а не M-AILABS, RUSLAN, Golos или FLEURS:

* M-AILABS и другие русские аудиокниги LibriVox: русская речь в clean-наборе DNS Challenge (`russian_speech`, 12 ГБ) взята из LibriVox, то есть это потенциальная утечка в пользу DFN;
* FLEURS: Sidon обучен на FLEURS-R, русский там есть;
* RUSLAN: один диктор;
* Golos crowd: подходит по составу, но лицензия SberDevices с условиями (не CC), качество записи то же краудсорсинговое;
* Common Voice: CC0, тысячи дикторов, нет ни в LibriTTS-R/FLEURS-R (Sidon), ни в clean-речи DNS (DFN). Минусы: бытовые микрофоны и MP3, их закрывает фильтр качества ниже. Whisper, вероятно, видел Common Voice при обучении, но это одинаково для всех систем и сдвигает только абсолютный CER.

In [7]:
NOISE_ROOT = hf_verified(*PINS['musan_noise'], WORK / 'raw' / 'musan_noise',
                         ['noise/free-sound/*.wav', 'noise/sound-bible/*.wav'])
noise_files = sorted((NOISE_ROOT / 'noise').rglob('*.wav'))
CV_ROOT = hf_verified(*PINS['cv17'], WORK / 'raw' / 'cv17', CV_SHARDS)
print('MUSAN noise:', len(noise_files), '| CV shards:', CV_SHARDS)

Fetching 930 files:   0%|          | 0/930 [00:00<?, ?it/s]

noise/free-sound/noise-free-sound-0002.w(…):   0%|          | 0.00/2.28M [00:00<?, ?B/s]

noise/free-sound/noise-free-sound-0003.w(…):   0%|          | 0.00/456k [00:00<?, ?B/s]

noise/free-sound/noise-free-sound-0000.w(…):   0%|          | 0.00/565k [00:00<?, ?B/s]

noise/free-sound/noise-free-sound-0001.w(…):   0%|          | 0.00/1.30M [00:00<?, ?B/s]

...

Fetching 3 files:   0%|          | 0/3 [00:00<?, ?it/s]

ru/test-00000-of-00008.parquet:   0%|          | 0.00/48.8M [00:00<?, ?B/s]

ru/test-00001-of-00008.parquet:   0%|          | 0.00/47.9M [00:00<?, ?B/s]

ru/test-00002-of-00008.parquet:   0%|          | 0.00/48.4M [00:00<?, ?B/s]

fixie-ai/common_voice_17_0@34f78a43: sha256 ok for 3 files
MUSAN noise: 930 | CV shards: ['ru/test-00000-of-00008.parquet', 'ru/test-00001-of-00008.parquet', 'ru/test-00002-of-00008.parquet']


### 4.1 Отбор дикторов

Один клип на диктора, порядок детерминирован (`sha256(seed:path)`), фильтр по голосам (`up_votes ≥ 2`, `down_votes = 0`), тишина по краям обрезается с запасом 0.25 с. Потом DNSMOS-скрининг, и в набор идут первые `N_SPEAKERS` клипов, прошедших порог качества.

In [9]:
import io
import numpy as np
import pandas as pd
import pyarrow.parquet as pq
import soundfile as sf
import soxr

SR = 16_000

def active_rms(audio, frame=320, floor_db=40.0):
    n = len(audio) // frame
    energy = np.mean(audio[:n * frame].astype(np.float64).reshape(n, frame) ** 2, axis=1) + 1e-20
    db = 10 * np.log10(energy)
    return float(np.sqrt(np.mean(energy[db > db.max() - floor_db])))

def trim_silence(audio, frame=320, floor_db=40.0, margin=0.25):
    n = len(audio) // frame
    energy = np.mean(audio[:n * frame].astype(np.float64).reshape(n, frame) ** 2, axis=1) + 1e-20
    db = 10 * np.log10(energy)
    active = np.flatnonzero(db > db.max() - floor_db)
    pad = int(margin * SR)
    return audio[max(0, active[0] * frame - pad): min(len(audio), (active[-1] + 1) * frame + pad)]

def stable_key(text):
    return hashlib.sha256(f'{SEED}:{text}'.encode()).hexdigest()

meta = pd.concat([pq.read_table(CV_ROOT / shard, columns=['client_id', 'path', 'sentence', 'up_votes', 'down_votes', 'gender'])
                  .to_pandas().assign(shard=shard, row=lambda d: range(len(d))) for shard in CV_SHARDS], ignore_index=True)
meta = meta[(meta.up_votes >= 2) & (meta.down_votes == 0) & (meta.sentence.str.split().str.len() >= 4)]
meta = meta.assign(key=meta.path.map(stable_key)).sort_values('key')
per_speaker = meta.groupby('client_id', sort=False).head(1)
per_speaker = per_speaker.assign(skey=per_speaker.client_id.map(stable_key)).sort_values('skey')
print('клипов после фильтра голосов:', len(meta), '| дикторов:', len(per_speaker))

CAND_DIR = WORK / f'candidates_{RUN_MODE}'
shutil.rmtree(CAND_DIR, ignore_errors=True)
DNSMOS_ONNX = fetch_url(*PINS['dnsmos_onnx'], WORK / 'models' / 'dnsmos_sig_bak_ovr.onnx')
tables = {shard: pq.read_table(CV_ROOT / shard, columns=['audio']) for shard in CV_SHARDS}
BATCH = max(4 * N_SPEAKERS // 3, 16)   # порог проходит примерно четверть; скрининг порциями, пока не наберётся N_SPEAKERS
screened, passed, queue = [], 0, list(per_speaker.itertuples())
while passed < N_SPEAKERS and queue:
    batch_dir = CAND_DIR / f'batch{len(screened):03d}'
    batch_dir.mkdir(parents=True)
    batch = []
    while queue and len(batch) < BATCH:
        rec = queue.pop(0)
        audio, sr = sf.read(io.BytesIO(tables[rec.shard].column('audio')[rec.row].as_py()['bytes']), dtype='float32')
        if audio.ndim == 2:
            audio = audio.mean(axis=1)
        audio = trim_silence(soxr.resample(audio, sr, SR, quality='VHQ').astype(np.float32))
        if not (CLIP_SECONDS[0] <= len(audio) / SR <= CLIP_SECONDS[1]):
            continue
        name = Path(rec.path).stem + '.wav'
        sf.write(batch_dir / name, audio, SR, subtype='FLOAT')
        batch.append({'file': name, 'path': batch_dir / name, 'client_id': rec.client_id, 'gender': rec.gender,
                      'sentence': rec.sentence, 'skey': rec.skey,
                      'source': f'{PINS["cv17"][0]}@{PINS["cv17"][1][:8]}:{rec.shard}#{Path(rec.path).name}'})
    if not batch:
        continue
    sh([PY_EV, BENCH / 'metrics.py', 'screen', '--input-dir', batch_dir, '--output', batch_dir / 'screen.csv',
        '--dnsmos-model', DNSMOS_ONNX])
    scored = pd.DataFrame(batch).merge(pd.read_csv(batch_dir / 'screen.csv'), on='file')
    scored['ok'] = np.logical_and.reduce([scored[k] >= v for k, v in QUALITY.items()])
    screened.append(scored)
    passed += int(scored.ok.sum())
    print(f'проверено {sum(map(len, screened))}, прошли порог {passed}')

screen = pd.concat(screened).sort_values('skey')
selected = screen[screen.ok].head(N_SPEAKERS).reset_index(drop=True)
if len(selected) < N_SPEAKERS:
    raise RuntimeError(f'Только {len(selected)} дикторов прошли порог. Добавь шард в CV_SHARDS или ослабь QUALITY.')
print(selected.gender.replace('', 'не указан').value_counts().to_string())

клипов после фильтра голосов: 3040 | дикторов: 1417
$ /content/ah_bench/venvs/ev312/bin/python /content/ah_bench/bench/metrics.py screen --input-dir /content/ah_bench/candidates_full/batch000 --output /content/ah_bench/candidates_full/batch000/screen.csv --dnsmos-model /content/ah_bench/models/dnsmos_sig_bak_ovr.onnx
screened 213 -> /content/ah_bench/candidates_full/batch000/screen.csv
проверено 213, прошли порог 49
$ /content/ah_bench/venvs/ev312/bin/python /content/ah_bench/bench/metrics.py screen --input-dir /content/ah_bench/candidates_full/batch001 --output /content/ah_bench/candidates_full/batch001/screen.csv --dnsmos-model /content/ah_bench/models/dnsmos_sig_bak_ovr.onnx
screened 213 -> /content/ah_bench/candidates_full/batch001/screen.csv
проверено 426, прошли порог 97
$ /content/ah_bench/venvs/ev312/bin/python /content/ah_bench/bench/metrics.py screen --input-dir /content/ah_bench/candidates_full/batch002 --output /content/ah_bench/candidates_full/batch002/screen.csv --dnsmos-

## 5. Замороженный test-набор

Логика смешивания та же, что у тебя (seed, SNR, общий пик), но с тремя изменениями:

1. уровень речи считается по активным кадрам, иначе паузы в клипе занижают RMS речи и реальный SNR оказывается выше заявленного;
2. у каждой пары свой генератор `default_rng([SEED, clip, snr])`, поэтому пара не зависит от порядка обхода и от числа других пар;
3. каждый клип идёт при всех трёх SNR (парный дизайн), шум ресемплируется через soxr.

После записи считается фактический SNR из сохранённых PCM_16-файлов. Если набор уже существует, ячейка только сверяет sha256 и ничего не пишет.

In [10]:
import csv

def fit_noise(audio, length, rng):
    if len(audio) >= length:
        start = int(rng.integers(len(audio) - length + 1))
        return audio[start:start + length]
    return np.tile(audio, int(np.ceil(length / len(audio))))[:length]

def load_noise(path):
    audio, sr = sf.read(path, dtype='float32', always_2d=False)
    if audio.ndim == 2:
        audio = audio.mean(axis=1)
    return soxr.resample(audio, sr, SR, quality='VHQ').astype(np.float32) if sr != SR else audio

def verify_testset(root):
    info = json.loads((root / 'testset.json').read_text())
    if sha256_file(root / 'manifest.csv') != info['manifest_sha256']:
        raise RuntimeError('manifest.csv изменён после заморозки')
    rows = list(csv.DictReader((root / 'manifest.csv').open(encoding='utf-8')))
    for row in rows:
        for col in ('clean', 'noise', 'noisy'):
            if sha256_file(root / row[col]) != row[f'sha256_{col}']:
                raise RuntimeError(f'{row[col]}: sha256 не совпадает с манифестом')
    print(f'набор заморожен и цел: {len(rows)} пар, manifest sha256 {info["manifest_sha256"][:16]}…')
    return rows

if REBUILD_TESTSET and EVAL_ROOT.exists():
    print('REBUILD_TESTSET=True: удаляю', EVAL_ROOT)
    shutil.rmtree(EVAL_ROOT)

if (EVAL_ROOT / 'testset.json').exists():
    manifest_rows = verify_testset(EVAL_ROOT)
else:
    for folder in ('clean', 'noise', 'noisy'):
        (EVAL_ROOT / folder).mkdir(parents=True, exist_ok=True)
    manifest_rows = []
    for clip_index, clip in selected.iterrows():
        clean = sf.read(clip.path, dtype='float32')[0]
        clean_id = f'c{clip_index:03d}'
        mixes = []
        for snr_db in SNRS_DB:
            rng = np.random.default_rng([SEED, clip_index, snr_db])
            while True:
                noise_path = noise_files[int(rng.integers(len(noise_files)))]
                noise = fit_noise(load_noise(noise_path), len(clean), rng)
                if np.sqrt(np.mean(noise.astype(np.float64) ** 2)) > 1e-5:   # пропускаем цифровую тишину
                    break
            noise = noise * (active_rms(clean) / np.sqrt(np.mean(noise.astype(np.float64) ** 2)) / 10 ** (snr_db / 20))
            mixes.append((snr_db, noise_path, noise))
        # Один множитель на клип для всех SNR: SNR сохраняется, и один clean-файл годится эталоном для всех трёх пар.
        peak = max([np.abs(clean).max()] + [np.abs(clean + noise).max() for _, _, noise in mixes])
        scale = min(1.0, 0.99 / peak)
        clean_rel = f'clean/{clean_id}.wav'
        sf.write(EVAL_ROOT / clean_rel, clean * scale, SR, subtype='PCM_16')
        for snr_db, noise_path, noise in mixes:
            item_id = f'{clean_id}_snr{snr_db:02d}'
            paths = {'clean': clean_rel, 'noise': f'noise/{item_id}.wav', 'noisy': f'noisy/{item_id}.wav'}
            sf.write(EVAL_ROOT / paths['noise'], noise * scale, SR, subtype='PCM_16')
            sf.write(EVAL_ROOT / paths['noisy'], (clean + noise) * scale, SR, subtype='PCM_16')
            manifest_rows.append({
                'id': item_id, 'clean_id': clean_id, **paths, 'snr_db': snr_db,
                'speaker': clip.client_id[:16], 'gender': clip.gender or 'unknown', 'sentence': clip.sentence,
                'source_clean': clip.source, 'source_noise': str(noise_path.relative_to(NOISE_ROOT)),
                'noise_subset': noise_path.parent.name, 'clean_dnsmos_ovrl': round(clip.dnsmos_ovrl, 3),
            })
    for row in manifest_rows:
        for col in ('clean', 'noise', 'noisy'):
            row[f'sha256_{col}'] = sha256_file(EVAL_ROOT / row[col])
    with (EVAL_ROOT / 'manifest.csv').open('w', newline='', encoding='utf-8') as handle:
        writer = csv.DictWriter(handle, fieldnames=list(manifest_rows[0]))
        writer.writeheader()
        writer.writerows(manifest_rows)
    (EVAL_ROOT / 'testset.json').write_text(json.dumps({
        'created': time.strftime('%Y-%m-%dT%H:%M:%SZ', time.gmtime()), 'seed': SEED, 'snrs_db': SNRS_DB,
        'n_speakers': N_SPEAKERS, 'quality_gate': QUALITY, 'clip_seconds': CLIP_SECONDS, 'pins': PINS,
        'manifest_sha256': sha256_file(EVAL_ROOT / 'manifest.csv'),
    }, indent=2, ensure_ascii=False))
    manifest_rows = verify_testset(EVAL_ROOT)

# Контроль: фактический SNR по записанным файлам (уровень речи по активным кадрам, как при смешивании)
realized = []
for row in manifest_rows:
    clean = sf.read(EVAL_ROOT / row['clean'], dtype='float32')[0]
    noise = sf.read(EVAL_ROOT / row['noise'], dtype='float32')[0]
    realized.append(20 * np.log10(active_rms(clean) / np.sqrt(np.mean(noise.astype(np.float64) ** 2))) - float(row['snr_db']))
print(f'отклонение фактического SNR от заданного: max |Δ| = {np.max(np.abs(realized)):.3f} дБ')
assert np.max(np.abs(realized)) < 0.1

набор заморожен и цел: 480 пар, manifest sha256 5e249887f7257fc5…
отклонение фактического SNR от заданного: max |Δ| = 0.032 дБ


## 6. Инференс

Обе модели работают на одном устройстве (T4 в full-режиме). Модель грузится один раз, первый файл прогоняется как прогрев, время каждого файла меряется с `torch.cuda.synchronize()`. Загрузка и прогрев пишутся в `run_info.json` отдельно от RTF. Уже готовые выходы пропускаются, так что после обрыва сессии работа продолжается с места остановки. Выход сохраняется в float32 на родной частоте модели (48 кГц у обеих) и приводится к 16 кГц только на этапе метрик.

DeepFilterNet3: `enhance(..., pad=True)` сам компенсирует задержку STFT. Веса берутся из того же `DeepFilterNet3.zip`, что качает `init_df()`, но с проверкой sha256.

In [11]:
DFN_DIR = WORK / 'models'
safe_unzip(fetch_url(*PINS['dfn3_zip'], WORK / 'models' / 'DeepFilterNet3.zip'), DFN_DIR)
sh([PY_DF, BENCH / 'run_deepfilter.py', '--root', EVAL_ROOT, '--model-dir', DFN_DIR / 'DeepFilterNet3',
    '--output-dir', EVAL_ROOT / 'deepfilter'])

$ /content/ah_bench/venvs/df311/bin/python /content/ah_bench/bench/run_deepfilter.py --root /content/drive/MyDrive/audio-harness/derived/denoise_eval_v2_full --model-dir /content/ah_bench/models/DeepFilterNet3 --output-dir /content/drive/MyDrive/audio-harness/derived/denoise_eval_v2_full/deepfilter
/content/ah_bench/venvs/df311/lib/python3.11/site-packages/df/io.py:9: UserWarning: `torchaudio.backend.common.AudioMetaData` has been moved to `torchaudio.AudioMetaData`. Please update the import path.
  from torchaudio.backend.common import AudioMetaData
fatal: not a git repository (or any of the parent directories): .git
/content/ah_bench/venvs/df311/lib/python3.11/site-packages/df/io.py:106: UserWarning: "sinc_interpolation" resampling method name is being deprecated and replaced by "sinc_interp_hann" in the next release. The default behavior remains unchanged.
  return ta_resample(audio, orig_sr, new_sr, **params)
/content/ah_bench/venvs/df311/lib/python3.11/site-packages/df/io.py:106: 

Sidon v0.1: тот же путь инференса, что в `tools/restore` harness (официальный демо-код): 16 кГц на входе, 48 кГц на выходе. На T4 используются CUDA-варианты TorchScript.

In [12]:
sh([PY_EV, BENCH / 'run_sidon.py', '--root', EVAL_ROOT, '--output-dir', EVAL_ROOT / 'sidon',
    '--revision', PINS['sidon'][1], '--preprocessor-revision', PINS['w2v_bert'][1],
    '--device', 'cuda' if HAS_GPU else 'cpu'])

$ /content/ah_bench/venvs/ev312/bin/python /content/ah_bench/bench/run_sidon.py --root /content/drive/MyDrive/audio-harness/derived/denoise_eval_v2_full --output-dir /content/drive/MyDrive/audio-harness/derived/denoise_eval_v2_full/sidon --revision b3b02d8bbd55fdbc410e6e46e76ef95ace4fbf52 --preprocessor-revision da985ba0987f70aaeb84a80f2851cfac8c697a7b --device cuda
1/480 c000_snr00: 7.325s
2/480 c000_snr05: 0.288s
3/480 c000_snr10: 0.275s
4/480 c001_snr00: 0.312s
5/480 c001_snr05: 5.995s
6/480 c001_snr10: 0.359s
7/480 c002_snr00: 0.249s
8/480 c002_snr05: 7.184s
9/480 c002_snr10: 0.311s
10/480 c003_snr00: 0.301s
11/480 c003_snr05: 0.290s
12/480 c003_snr10: 0.296s
13/480 c004_snr00: 0.355s
14/480 c004_snr05: 0.294s
15/480 c004_snr10: 0.301s
16/480 c005_snr00: 0.178s
17/480 c005_snr05: 0.173s
18/480 c005_snr10: 0.196s
19/480 c006_snr00: 0.256s
20/480 c006_snr05: 0.258s
21/480 c006_snr10: 0.263s
22/480 c007_snr00: 0.264s
23/480 c007_snr05: 0.258s
24/480 c007_snr10: 0.268s
25/480 c008_snr0

## 7. Метрики

| Метрика | Что ловит | Честна к Sidon? |
|---|---|---|
| DNSMOS P.835 SIG / BAK / OVRL | искажения речи, остаточный шум, общее качество (без эталона) | да |
| UTMOS22 | естественность (без эталона; обучен на английском) | да |
| CER, Whisper | разборчивость и галлюцинации генеративной модели: Sidon при 0 дБ может «досинтезировать» не те слова | да |
| ECAPA cosine с чистым эталоном | сохранность голоса: генеративная модель может сдвинуть тембр | да |
| SI-SDR, PESQ-WB, ESTOI (после выравнивания) | точность восстановления формы волны | **нет**: Sidon не сохраняет фазу, это контроль для DFN |

Все сигналы перед безэталонными метриками приводятся к −26 dBFS по активной речи, чтобы громкость выхода не влияла на оценку. Строки `clean` дают потолок для MOS-метрик и пол для CER.

In [13]:
sh([PY_EV, BENCH / 'metrics.py', 'evaluate', '--root', EVAL_ROOT, '--dnsmos-model', DNSMOS_ONNX,
    '--whisper', PINS['whisper'][0], '--whisper-revision', PINS['whisper'][1],
    '--utmos-revision', PINS['utmos'][1], '--ecapa-revision', PINS['ecapa'][1],
    '--cache', WORK / 'models', '--batch-size', '16' if HAS_GPU else '4'])

$ /content/ah_bench/venvs/ev312/bin/python /content/ah_bench/bench/metrics.py evaluate --root /content/drive/MyDrive/audio-harness/derived/denoise_eval_v2_full --dnsmos-model /content/ah_bench/models/dnsmos_sig_bak_ovr.onnx --whisper openai/whisper-large-v3-turbo --whisper-revision 41f01f3fe87f28c78e2fbf8b568835947dd65ed9 --utmos-revision eecd3e6e7ad9dd794308a4338c3ac7cb34691af9 --ecapa-revision 0f99f2d0ebe89ac095bcc5903c4dd8f72b367286 --cache /content/ah_bench/models --batch-size 16
Device set to use cuda
/content/ah_bench/venvs/ev312/lib/python3.12/site-packages/speechbrain/utils/torch_audio_backend.py:57: UserWarning: torchaudio._backend.list_audio_backends has been deprecated. This deprecation is part of a large refactoring effort to transition TorchAudio into a maintenance phase. The decoding and encoding capabilities of PyTorch for both audio and video are being consolidated into TorchCodec. Please see https://github.com/pytorch/audio/issues/3902 for more information. It will be 

## 8. Результаты

95% CI считается bootstrap по клипам (2000 повторов). Клип = диктор, поэтому это и кластерный bootstrap по дикторам. Парная разница Sidon − DFN считается на одних и тех же парах. Для CER «лучше» значит меньше, для остального больше.

In [14]:
manifest = pd.read_csv(EVAL_ROOT / 'manifest.csv')
metrics = {s: pd.read_csv(EVAL_ROOT / 'metrics' / f'{s}.csv') for s in ('clean', 'noisy', 'deepfilter', 'sidon')
           if (EVAL_ROOT / 'metrics' / f'{s}.csv').exists()}
items = pd.concat([m for s, m in metrics.items() if s != 'clean']).merge(manifest[['id', 'clean_id', 'snr_db', 'noise_subset']], on='id')
DECISION = ['dnsmos_ovrl', 'dnsmos_sig', 'dnsmos_bak', 'utmos', 'cer', 'spk_sim']
INTRUSIVE = ['si_sdr', 'pesq_wb', 'estoi', 'lag_ms']
rng = np.random.default_rng(SEED)

def boot(values, n=2000):
    values = np.asarray(values, dtype=float)
    values = values[~np.isnan(values)]
    if len(values) == 0:
        return np.nan, np.nan, np.nan
    means = values[rng.integers(0, len(values), (n, len(values)))].mean(axis=1)
    return values.mean(), *np.percentile(means, [2.5, 97.5])

def table(df, cols, by):
    out = []
    for key, group in df.groupby(by):
        rec = dict(zip(by, key if isinstance(key, tuple) else (key,)), n=len(group))
        for col in cols:
            mean, lo, hi = boot(group[col])
            rec[col] = f'{mean:.3f} [{lo:.3f}, {hi:.3f}]'
        out.append(rec)
    return pd.DataFrame(out)

pd.set_option('display.width', 250, 'display.max_columns', 30)
if 'clean' in metrics:
    print('Потолок (чистые эталоны):')
    display(table(metrics['clean'].assign(system='clean'), DECISION, ['system']))
print('Решающие метрики по SNR:')
display(table(items, DECISION, ['system', 'snr_db']))
print('Решающие метрики, все SNR вместе (сначала среднее по клипу):')
display(table(items.groupby(['system', 'clean_id'])[DECISION].mean().reset_index(), DECISION, ['system']))
print('Интрузивные метрики (контроль DFN, не для сравнения с Sidon):')
display(table(items, INTRUSIVE, ['system', 'snr_db']))

Потолок (чистые эталоны):


,system,n,dnsmos_ovrl,dnsmos_sig,dnsmos_bak,utmos,cer,spk_sim
0,clean,160,"3.315 [3.304, 3.326]","3.584 [3.575, 3.592]","4.109 [4.098, 4.120]","2.855 [2.786, 2.930]","0.017 [0.008, 0.029]","1.000 [1.000, 1.000]"


Решающие метрики по SNR:


,system,snr_db,n,dnsmos_ovrl,dnsmos_sig,dnsmos_bak,utmos,cer,spk_sim
0,deepfilter,0,160,"3.004 [2.965, 3.043]","3.290 [3.252, 3.327]","4.010 [3.984, 4.035]","2.241 [2.164, 2.315]","0.225 [0.114, 0.422]","0.735 [0.709, 0.761]"
1,deepfilter,5,160,"3.145 [3.115, 3.174]","3.408 [3.378, 3.437]","4.085 [4.071, 4.098]","2.506 [2.431, 2.578]","0.180 [0.064, 0.391]","0.814 [0.792, 0.836]"
2,deepfilter,10,160,"3.207 [3.182, 3.231]","3.456 [3.434, 3.479]","4.116 [4.104, 4.127]","2.646 [2.579, 2.713]","0.046 [0.032, 0.061]","0.858 [0.841, 0.876]"
3,noisy,0,160,"1.931 [1.835, 2.022]","2.684 [2.534, 2.817]","2.051 [1.928, 2.173]","1.454 [1.414, 1.500]","0.075 [0.055, 0.096]","0.792 [0.769, 0.813]"
4,noisy,5,160,"2.229 [2.144, 2.318]","3.108 [2.987, 3.209]","2.375 [2.258, 2.494]","1.586 [1.528, 1.643]","0.031 [0.021, 0.042]","0.860 [0.843, 0.874]"
5,noisy,10,160,"2.514 [2.446, 2.581]","3.367 [3.298, 3.424]","2.773 [2.670, 2.882]","1.842 [1.769, 1.917]","0.023 [0.013, 0.036]","0.891 [0.878, 0.904]"
6,sidon,0,160,"3.378 [3.361, 3.394]","3.602 [3.588, 3.616]","4.183 [4.177, 4.189]","3.395 [3.344, 3.443]","0.096 [0.072, 0.123]","0.722 [0.703, 0.741]"
7,sidon,5,160,"3.386 [3.368, 3.403]","3.609 [3.595, 3.623]","4.185 [4.178, 4.192]","3.433 [3.380, 3.484]","0.048 [0.034, 0.063]","0.762 [0.747, 0.776]"
8,sidon,10,160,"3.374 [3.356, 3.393]","3.601 [3.586, 3.616]","4.177 [4.168, 4.186]","3.422 [3.371, 3.474]","0.032 [0.018, 0.048]","0.791 [0.779, 0.803]"


Решающие метрики, все SNR вместе (сначала среднее по клипу):


,system,n,dnsmos_ovrl,dnsmos_sig,dnsmos_bak,utmos,cer,spk_sim
0,deepfilter,160,"3.118 [3.096, 3.142]","3.385 [3.363, 3.406]","4.070 [4.058, 4.082]","2.464 [2.399, 2.525]","0.150 [0.074, 0.289]","0.803 [0.788, 0.817]"
1,noisy,160,"2.225 [2.176, 2.272]","3.053 [2.987, 3.116]","2.399 [2.338, 2.461]","1.627 [1.588, 1.668]","0.043 [0.033, 0.055]","0.848 [0.836, 0.859]"
2,sidon,160,"3.379 [3.365, 3.394]","3.604 [3.591, 3.617]","4.182 [4.176, 4.188]","3.417 [3.374, 3.462]","0.059 [0.046, 0.073]","0.758 [0.747, 0.769]"


Интрузивные метрики (контроль DFN, не для сравнения с Sidon):


,system,snr_db,n,si_sdr,pesq_wb,estoi,lag_ms
0,deepfilter,0,160,"10.292 [9.652, 10.960]","1.774 [1.705, 1.848]","0.754 [0.734, 0.775]","0.000 [0.000, 0.000]"
1,deepfilter,5,160,"12.865 [12.158, 13.622]","2.109 [2.017, 2.204]","0.827 [0.809, 0.844]","0.000 [0.000, 0.000]"
2,deepfilter,10,160,"14.938 [14.250, 15.590]","2.365 [2.272, 2.457]","0.873 [0.859, 0.887]","0.000 [0.000, 0.000]"
3,noisy,0,160,"-1.009 [-1.132, -0.871]","1.185 [1.155, 1.217]","0.626 [0.601, 0.651]","0.000 [0.000, 0.000]"
4,noisy,5,160,"4.047 [3.868, 4.252]","1.364 [1.311, 1.427]","0.735 [0.713, 0.757]","0.000 [0.000, 0.000]"
5,noisy,10,160,"9.053 [8.895, 9.233]","1.514 [1.450, 1.581]","0.809 [0.791, 0.826]","0.000 [0.000, 0.000]"
6,sidon,0,160,"-13.226 [-13.744, -12.726]","1.554 [1.509, 1.603]","0.712 [0.695, 0.729]","5.344 [4.146, 6.611]"
7,sidon,5,160,"-13.006 [-13.476, -12.554]","1.630 [1.584, 1.679]","0.742 [0.725, 0.759]","5.014 [3.761, 6.324]"
8,sidon,10,160,"-12.980 [-13.425, -12.501]","1.710 [1.656, 1.765]","0.752 [0.734, 0.768]","7.169 [5.885, 8.511]"


In [15]:
# Парная разница Sidon − DFN на одних и тех же парах
if {'deepfilter', 'sidon'} <= set(metrics):
    paired = metrics['sidon'].set_index('id')[DECISION] - metrics['deepfilter'].set_index('id')[DECISION]
    paired = paired.join(manifest.set_index('id')[['snr_db', 'clean_id']])
    rows = []
    for snr, group in [('все', paired.groupby('clean_id')[DECISION].mean())] + list(paired.groupby('snr_db')):
        rec = {'snr_db': snr, 'n': len(group)}
        for col in DECISION:
            mean, lo, hi = boot(group[col])
            better = (group[col] < 0).mean() if col == 'cer' else (group[col] > 0).mean()
            rec[col] = f'{mean:+.3f} [{lo:+.3f}, {hi:+.3f}] / Sidon лучше в {better:.0%}'
        rows.append(rec)
    print('Sidon − DFN (CER: минус = Sidon лучше; остальное: плюс = Sidon лучше). CI, не накрывающий 0, = значимая разница:')
    display(pd.DataFrame(rows))
    print('Решающие метрики по подмножеству шумов (free-sound пересекается с шумами DNS):')
    display(table(items[items.system != 'noisy'], ['dnsmos_ovrl', 'cer', 'spk_sim'], ['system', 'noise_subset']))

Sidon − DFN (CER: минус = Sidon лучше; остальное: плюс = Sidon лучше). CI, не накрывающий 0, = значимая разница:


,snr_db,n,dnsmos_ovrl,dnsmos_sig,dnsmos_bak,utmos,cer,spk_sim
0,все,160,"+0.261 [+0.239, +0.284] / Sidon лучше в 99%","+0.220 [+0.200, +0.240] / Sidon лучше в 99%","+0.112 [+0.100, +0.125] / Sidon лучше в 96%","+0.953 [+0.896, +1.010] / Sidon лучше в 100%","-0.091 [-0.225, -0.021] / Sidon лучше в 60%","-0.044 [-0.054, -0.034] / Sidon лучше в 22%"
1,0,160,"+0.374 [+0.334, +0.414] / Sidon лучше в 99%","+0.312 [+0.276, +0.351] / Sidon лучше в 98%","+0.173 [+0.147, +0.201] / Sidon лучше в 96%","+1.155 [+1.076, +1.235] / Sidon лучше в 98%","-0.129 [-0.318, -0.022] / Sidon лучше в 48%","-0.013 [-0.030, +0.006] / Sidon лучше в 37%"
2,5,160,"+0.241 [+0.212, +0.271] / Sidon лучше в 92%","+0.201 [+0.175, +0.230] / Sidon лучше в 93%","+0.100 [+0.086, +0.114] / Sidon лучше в 89%","+0.927 [+0.855, +1.001] / Sidon лучше в 99%","-0.132 [-0.336, -0.023] / Sidon лучше в 35%","-0.053 [-0.068, -0.037] / Sidon лучше в 22%"
3,10,160,"+0.168 [+0.144, +0.192] / Sidon лучше в 85%","+0.145 [+0.122, +0.166] / Sidon лучше в 85%","+0.061 [+0.050, +0.073] / Sidon лучше в 79%","+0.776 [+0.714, +0.838] / Sidon лучше в 99%","-0.014 [-0.025, -0.001] / Sidon лучше в 28%","-0.067 [-0.080, -0.053] / Sidon лучше в 18%"


Решающие метрики по подмножеству шумов (free-sound пересекается с шумами DNS):


,system,noise_subset,n,dnsmos_ovrl,cer,spk_sim
0,deepfilter,free-sound,445,"3.120 [3.098, 3.141]","0.122 [0.080, 0.194]","0.804 [0.789, 0.817]"
1,deepfilter,sound-bible,35,"3.100 [3.016, 3.172]","0.502 [0.025, 1.430]","0.789 [0.737, 0.839]"
2,sidon,free-sound,445,"3.379 [3.368, 3.389]","0.060 [0.048, 0.072]","0.759 [0.750, 0.769]"
3,sidon,sound-bible,35,"3.387 [3.355, 3.418]","0.048 [0.021, 0.081]","0.745 [0.702, 0.784]"


In [16]:
# Скорость: RTF без загрузки и прогрева
speed = []
for system in ('deepfilter', 'sidon'):
    folder = EVAL_ROOT / system
    if not (folder / 'timings.csv').exists():
        continue
    timing = pd.read_csv(folder / 'timings.csv')
    info = json.loads((folder / 'run_info.json').read_text())
    rtf = timing.seconds / timing.audio_seconds
    speed.append({'system': system, 'device': info['device'], 'load_s': round(info['load_seconds'], 1),
                  'warmup_s': round(info['warmup_seconds'], 2), 'files': len(timing),
                  'rtf_median': round(rtf.median(), 4), 'rtf_p90': round(rtf.quantile(0.9), 4)})
display(pd.DataFrame(speed))

,system,device,load_s,warmup_s,files,rtf_median,rtf_p90
0,deepfilter,cuda:0,0.7,0.93,480,0.0085,0.0118
1,sidon,cuda,12.1,3.11,480,0.0515,0.0571


In [17]:
# Послушать: два случайных клипа при 0 дБ (noisy, DFN, Sidon, clean)
from IPython.display import Audio, display as show
for item_id in manifest[manifest.snr_db == 0].sample(2, random_state=SEED).id:
    row = manifest.set_index('id').loc[item_id]
    print(item_id, '|', row.sentence)
    for label, path in [('noisy', row.noisy), ('deepfilter', f'deepfilter/{item_id}.wav'), ('sidon', f'sidon/{item_id}.wav'), ('clean', row.clean)]:
        if (EVAL_ROOT / path).exists():
            audio, sr = sf.read(EVAL_ROOT / path, dtype='float32')
            print(label); show(Audio(audio, rate=sr))

c105_snr00 | Необходимы также всеобъемлющие профилактические меры.
noisy


deepfilter


sidon


clean


c108_snr00 | Я хочу заверить их в полном сотрудничестве моей делегации.
noisy


deepfilter


sidon


clean


In [18]:
# Сводка в CSV рядом с набором
RESULTS = EVAL_ROOT / 'results'
RESULTS.mkdir(exist_ok=True)
items.to_csv(RESULTS / 'per_file.csv', index=False)
table(items, DECISION + INTRUSIVE, ['system', 'snr_db']).to_csv(RESULTS / 'summary.csv', index=False)
pd.DataFrame(speed).to_csv(RESULTS / 'speed.csv', index=False)
print('CSV:', RESULTS)

CSV: /content/drive/MyDrive/audio-harness/derived/denoise_eval_v2_full/results


## Как читать результат

* **Главный вопрос: какую модель ставить в `denoise`.** Смотри на парную разницу. Если Sidon значимо лучше по DNSMOS OVRL и UTMOS, а CER и speaker similarity у него не хуже DFN (CI разницы накрывает 0 или в его пользу), он годится как основной. Если CER при 0 дБ у Sidon заметно выше, он подменяет слова, и для речи, которая потом пойдёт в ASR или агенту, это хуже остаточного шума.
* **Скорость.** DFN на T4 должен быть на порядок быстрее. Для harness это аргумент держать DFN как быстрый режим, а Sidon как «восстановление».
* **Лицензии.** Common Voice CC0; MUSAN CC BY 4.0 (нужна атрибуция); DeepFilterNet MIT/Apache-2.0; Sidon MIT (w2v-BERT 2.0 MIT); UTMOS22 MIT; Whisper MIT (large-v3-turbo) и Apache-2.0 (small); ECAPA speechbrain Apache-2.0; DNSMOS из репозитория DNS Challenge (CC BY 4.0 / MIT, см. репозиторий). Для внутреннего бенчмарка ограничений нет.